# Batch nylon PDB alignment

This notebook uses the same rigid-body alignment logic as `align_nylon.py`, but loops over all PDB files in one folder. Every structure is aligned **directly to the same reference structure**, so all outputs share the same coordinate frame.

In [1]:
# =========================
# CONFIGURATION
# =========================
from pathlib import Path

REFERENCE_PDB = Path("/home/chiara/Desktop/COMENZE/Surfmatch_pipeline/Nylon_surface/Nylon_surfmap/NYL_newVer_rotY90resnum.pdb")
INPUT_DIR = Path("/home/chiara/Desktop/COMENZE/Surfmatch_pipeline/Nylon_surface/Nylon_cube/final_structure/output_nylon/pqr_to_pdb_bfactor")
OUTPUT_DIR = Path("/home/chiara/Desktop/COMENZE/Surfmatch_pipeline/Nylon_surface/Nylon_cube/final_structure/output_nylon")
PATTERN = "*.pdb"

# Same defaults as the original script
ANCHORS = ["A:1=A:1"]
ATOMS = ('N', 'C1', 'C2', 'C3', 'C4', 'C5', 'C6', 'O')
RESNAME = "NYL"
CENTER = "reference"
MAX_ANCHOR_RMSD = 0.15
OVERWRITE = True


## Alignment functions

The functions below are taken from the supplied script so the notebook is self-contained.

In [2]:
#!/usr/bin/env python3
"""
how to use: 
python align_nylon.py --reference nylon_aligned_for_reference.pdb --inputs input_nylon_to_align.pdb --output-dir aligned_nylon_output_dir

outputs:
- aligned PDB files in specified output directory
- JSON report files in specified output directory
"""


import argparse
import csv
import hashlib
import json
import re
import sys
from dataclasses import dataclass
from pathlib import Path
import numpy as np

DEFAULT_NAMES = ('N', 'C1', 'C2', 'C3', 'C4', 'C5', 'C6', 'O')

@dataclass
class Structure:
    path: Path
    lines: list
    atom_lines: list
    xyz: np.ndarray
    residues: dict

def read_pdb(path):
    path = Path(path)
    lines = path.read_text().splitlines(keepends=True)
    atoms, xyz, residues = [], [], {}
    if sum(line[:6].strip() == 'MODEL' for line in lines) > 1:
        raise ValueError(f'{path}: multiple MODELs are unsupported; select one first.')
    for line_number, line in enumerate(lines):
        record = line[:6].strip()
        if record in {'CRYST1', 'SCALE1', 'SCALE2', 'SCALE3', 'ORIGX1', 'ORIGX2',
                      'ORIGX3', 'MTRIX1', 'MTRIX2', 'MTRIX3'}:
            raise ValueError(f'{path}: {record} is frame-dependent; prepare a finite-block PDB without these records first.')
        if record not in {'ATOM', 'HETATM'}:
            continue
        if len(line.rstrip('\r\n')) < 54:
            raise ValueError(f'{path}:{line_number+1}: truncated coordinate record.')
        if line[16] != ' ':
            raise ValueError(f'{path}:{line_number+1}: select one alternate conformer first.')
        try:
            point = [float(line[a:a+8]) for a in (30, 38, 46)]
            resid = int(line[22:26])
        except ValueError as exc:
            raise ValueError(f'{path}:{line_number+1}: invalid XYZ or residue number.') from exc
        key = (line[21], resid, line[26])
        name = line[12:16].strip()
        residue = residues.setdefault(key, {'resname': line[17:20].strip(), 'atoms': {}})
        if residue['resname'] != line[17:20].strip() or name in residue['atoms']:
            raise ValueError(f'{path}: ambiguous residue/duplicate atom {key}, {name}; use unique chain and residue IDs.')
        residue['atoms'][name] = len(xyz)
        atoms.append(line_number)
        xyz.append(point)
    array = np.asarray(xyz, dtype=float)
    if len(array) < 3 or not np.isfinite(array).all():
        raise ValueError(f'{path}: insufficient atoms or nonfinite coordinates.')
    return Structure(path, lines, atoms, array, residues)


def parse_residue(text):
    match = re.fullmatch(r'([^:]):(-?\d+)([A-Za-z]?)', text)
    chain, number, insertion = match.groups()
    return (' ' if chain == '_' else chain, int(number), insertion or ' ')


def residue_label(key):
    return f"{key[0] if key[0] != ' ' else '_'}:{key[1]}{key[2].strip()}"


def anchor_points(structure, key, names, resname):
    residue = structure.residues.get(key)
    if residue is None:
        raise ValueError(f'{structure.path}: anchor {residue_label(key)} not found; specify --anchor explicitly.')
    if residue['resname'] != resname:
        raise ValueError(f'{structure.path}: anchor {residue_label(key)} is {residue["resname"]}, expected {resname}.')
    missing = set(names) - set(residue['atoms'])
    if missing:
        raise ValueError(f'{structure.path}: anchor {residue_label(key)} lacks atoms {sorted(missing)}.')
    return structure.xyz[[residue['atoms'][name] for name in names]]


def fit_orientation(mobile, reference, pairs, names, resname, rmsd_limit):
    source, target = [], []
    for mkey, rkey in pairs:
        a = anchor_points(mobile, mkey, names, resname)
        b = anchor_points(reference, rkey, names, resname)
        source.append(a - a.mean(axis=0))
        target.append(b - b.mean(axis=0))
    a, b = np.vstack(source), np.vstack(target)
    for label, arr in [('mobile', a), ('reference', b)]:
        sv = np.linalg.svd(arr, compute_uv=False)
        if sv[0] <= 1e-12 or sv[1] / sv[0] < 1e-3:
            raise ValueError(f'{label}: anchor geometry is almost collinear; choose a wider chemical motif.')
    u, singular, vt = np.linalg.svd(a.T @ b)
    correction = np.eye(3)
    correction[2, 2] = 1. if np.linalg.det(u @ vt) > 0 else -1.
    rotation = u @ correction @ vt  
    if not np.allclose(rotation.T @ rotation, np.eye(3), atol=1e-10) or not np.isclose(np.linalg.det(rotation), 1.):
        raise ValueError('A proper rigid rotation could not be determined.')
    errors = []
    for pair, aa, bb in zip(pairs, source, target):
        rmsd = float(np.sqrt(np.mean(np.sum((aa @ rotation - bb)**2, axis=1))))
        errors.append({'mobile': residue_label(pair[0]), 'reference': residue_label(pair[1]),
                       'centred_motif_RMSD_A': rmsd})
        if rmsd > rmsd_limit:
            raise ValueError(f'Anchor {errors[-1]["mobile"]}: centred motif RMSD {rmsd:.4f} Å exceeds {rmsd_limit:g} Å. '
                             'Check anchor equivalence/conformation; do not increase tolerance without inspection.')
    return rotation, errors, singular


def transform_lines(structure, rotation, shift):
    out = structure.lines.copy()
    transformed = structure.xyz @ rotation + shift
    for line_index, point in zip(structure.atom_lines, transformed):
        fields = [f'{v:8.3f}' for v in point]
        if any(len(field) != 8 for field in fields):
            raise ValueError('Transformed coordinates exceed fixed-width PDB limits.')
        line = out[line_index]
        out[line_index] = line[:30] + ''.join(fields) + line[54:]
    for i, line in enumerate(out):
        if line[:6].strip() == 'ANISOU':
            try:
                q = [int(line[j:j+7]) for j in (28, 35, 42, 49, 56, 63)]
            except ValueError as exc:
                raise ValueError('Malformed ANISOU record.') from exc
            tensor = np.array([[q[0], q[3], q[4]], [q[3], q[1], q[5]], [q[4], q[5], q[2]]], float)
            rotated = rotation.T @ tensor @ rotation
            values = [rotated[0, 0], rotated[1, 1], rotated[2, 2], rotated[0, 1], rotated[0, 2], rotated[1, 2]]
            fields = [f'{int(np.rint(v)):7d}' for v in values]
            if any(len(f) != 7 for f in fields):
                raise ValueError('Rotated ANISOU exceeds PDB field limits.')
            out[i] = line[:28] + ''.join(fields) + line[70:]
    return out, transformed


def align_one(mobile, reference, pairs, names, resname='NYL', center='reference', rmsd_limit=.15):
    rotation, errors, singular = fit_orientation(mobile, reference, pairs, names, resname, rmsd_limit)
    source_center = mobile.xyz.mean(axis=0)
    reference_center = reference.xyz.mean(axis=0)
    target_center = reference_center if center == 'reference' else np.zeros(3)
    shift = target_center - source_center @ rotation
    lines, aligned = transform_lines(mobile, rotation, shift)
    bounds = np.array([aligned.min(axis=0), aligned.max(axis=0)])
    ray_anchor = np.array([bounds[0, 0], target_center[1], target_center[2]])
    report = {
        'mobile': str(mobile.path), 'reference': str(reference.path),
        'mobile_sha256': hashlib.sha256(mobile.path.read_bytes()).hexdigest(),
        'reference_sha256': hashlib.sha256(reference.path.read_bytes()).hexdigest(),
        'atom_count': len(mobile.xyz), 'reference_atom_count': len(reference.xyz),
        'method': 'Proper Kabsch rotation of chemically matched, individually centred repeat units',
        'anchor_atom_names': list(names), 'anchors': errors,
        'transform_equation': 'xyz_aligned = xyz_input @ rotation_row + translation_A',
        'rotation_row': rotation.tolist(), 'translation_A': shift.tolist(),
        'rotation_determinant': float(np.linalg.det(rotation)),
        'source_geometric_centroid_A': source_center.tolist(),
        'target_geometric_centroid_A': target_center.tolist(),
        'center_mode': center, 'centering_atom_selection': 'all ATOM and HETATM records',
        'aligned_bounds_A': bounds.tolist(), 'aligned_extent_A': np.ptp(aligned, axis=0).tolist(),
        'audited_SURFMAP_central_direction_aligned': [-1., 0., 0.],
        'equivalent_direction_in_input_frame': (np.array([-1., 0., 0.]) @ rotation.T).tolist(),
        'negative_X_atomic_support_anchor_A': ray_anchor.tolist(),
        }
    return lines, report

## Run the batch alignment

## Automatic mobile-anchor selection

The reference anchor remains fixed (default: `A:1`).

For each mobile nylon cube, the notebook does **not** assume that `A:1` exists.
Instead it:

1. finds all `NYL` residues containing the required anchor atoms;
2. tests their local geometry against the reference anchor;
3. keeps geometrically compatible candidates;
4. chooses the compatible residue closest to the geometric centre of that cube.

This makes the batch robust to different chain IDs, residue numbering, and cube sizes while preserving a common reference orientation.

In [3]:
# =========================
# AUTOMATIC MOBILE ANCHOR
# =========================

def candidate_anchor_residues(structure, names, resname="NYL"):
    """Return residues that can serve as complete chemical anchors."""
    candidates = []
    required = set(names)

    for key, residue in structure.residues.items():
        if residue["resname"] != resname:
            continue
        if required.issubset(residue["atoms"]):
            candidates.append(key)

    return candidates


def residue_centroid(structure, key, names):
    pts = anchor_points(structure, key, names, structure.residues[key]["resname"])
    return pts.mean(axis=0)


def choose_mobile_anchor(
    mobile,
    reference,
    reference_key,
    names,
    resname="NYL",
    rmsd_limit=0.15,
):
    """
    Select a chemically/geometrically compatible anchor automatically.

    Priority:
      1) centred local motif RMSD must be <= rmsd_limit
      2) among valid motifs, choose the residue nearest the mobile cube centroid
    """
    candidates = candidate_anchor_residues(mobile, names, resname)

    if not candidates:
        available = [
            f"{residue_label(k)}:{r['resname']}"
            for k, r in mobile.residues.items()
        ]
        preview = ", ".join(available[:20])
        raise ValueError(
            f"{mobile.path}: no {resname} residue contains all anchor atoms {list(names)}. "
            f"First residues found: {preview}"
        )

    cube_center = mobile.xyz.mean(axis=0)
    valid = []

    for key in candidates:
        try:
            rotation, errors, singular = fit_orientation(
                mobile,
                reference,
                [(key, reference_key)],
                names,
                resname,
                rmsd_limit,
            )
        except (ValueError, np.linalg.LinAlgError):
            continue

        local_rmsd = errors[0]["centred_motif_RMSD_A"]
        motif_center = residue_centroid(mobile, key, names)
        distance_to_cube_center = float(np.linalg.norm(motif_center - cube_center))

        valid.append({
            "key": key,
            "local_rmsd_A": local_rmsd,
            "distance_to_cube_center_A": distance_to_cube_center,
        })

    if not valid:
        raise ValueError(
            f"{mobile.path}: residues with the required atoms were found, "
            f"but none matched the reference anchor within {rmsd_limit:g} Å RMSD."
        )

    # Prefer a central repeat unit; RMSD is already constrained by the acceptance threshold.
    valid.sort(key=lambda x: (x["distance_to_cube_center_A"], x["local_rmsd_A"]))
    best = valid[0]

    return best["key"], valid


In [4]:
# =========================
# BATCH ALIGNMENT
# =========================
import csv

# The REFERENCE anchor remains fixed.
reference_pairs = []
for spec in ANCHORS:
    if spec.count("=") != 1:
        raise ValueError("Each anchor must have MOBILE=REFERENCE form.")
    a, b = spec.split("=")
    reference_pairs.append((parse_residue(a), parse_residue(b)))

if len(reference_pairs) != 1:
    raise ValueError(
        "Automatic mobile-anchor mode currently expects one reference anchor."
    )

# In automatic mode the mobile side of ANCHORS is ignored;
# only the REFERENCE residue on the right-hand side is fixed.
REFERENCE_ANCHOR_KEY = reference_pairs[0][1]

reference = read_pdb(REFERENCE_PDB)
anchor_points(reference, REFERENCE_ANCHOR_KEY, ATOMS, RESNAME)

OUTPUT_DIR.mkdir(parents=True, exist_ok=True)

reference_resolved = REFERENCE_PDB.resolve()
files = sorted(
    p for p in INPUT_DIR.glob(PATTERN)
    if p.is_file() and p.resolve() != reference_resolved
)

if not files:
    raise FileNotFoundError(f"No PDB files found in {INPUT_DIR.resolve()}")

print("Reference:", REFERENCE_PDB)
print("Reference centroid (Å):", reference.xyz.mean(axis=0))
print("Fixed reference anchor:", residue_label(REFERENCE_ANCHOR_KEY))
print(f"Found {len(files)} PDB file(s).")
print("Mobile anchor: selected automatically for each cube.")
print("All PDBs are aligned independently to the SAME reference coordinate frame.\n")

summary_rows = []

for path in files:
    output = OUTPUT_DIR / f"{path.stem}_aligned.pdb"
    audit = OUTPUT_DIR / f"{path.stem}_alignment.json"

    try:
        if not OVERWRITE and (output.exists() or audit.exists()):
            raise FileExistsError(
                f"{output.name} or its report already exists."
            )

        mobile = read_pdb(path)

        mobile_anchor_key, anchor_candidates = choose_mobile_anchor(
            mobile,
            reference,
            REFERENCE_ANCHOR_KEY,
            ATOMS,
            resname=RESNAME,
            rmsd_limit=MAX_ANCHOR_RMSD,
        )

        pairs_for_this_structure = [
            (mobile_anchor_key, REFERENCE_ANCHOR_KEY)
        ]

        lines, report = align_one(
            mobile,
            reference,
            pairs_for_this_structure,
            ATOMS,
            RESNAME,
            CENTER,
            MAX_ANCHOR_RMSD
        )

        report["automatic_mobile_anchor"] = residue_label(mobile_anchor_key)
        report["automatic_anchor_candidates"] = [
            {
                "residue": residue_label(row["key"]),
                "local_rmsd_A": row["local_rmsd_A"],
                "distance_to_cube_center_A": row["distance_to_cube_center_A"],
            }
            for row in anchor_candidates
        ]

        coords = np.array([
            [float(lines[k][j:j+8]) for j in (30, 38, 46)]
            for k in mobile.atom_lines
        ])

        output.write_text("".join(lines))
        audit.write_text(json.dumps(report, indent=2) + "\n")

        maximum = max(
            row["centred_motif_RMSD_A"]
            for row in report["anchors"]
        )

        summary_rows.append({
            "input_file": path.name,
            "status": "OK",
            "selected_mobile_anchor": residue_label(mobile_anchor_key),
            "atom_count": len(coords),
            "max_anchor_RMSD_A": maximum,
            "aligned_pdb": str(output),
            "json_report": str(audit),
            "error": ""
        })

        print(
            f"OK  {path.name:35s} "
            f"anchor={residue_label(mobile_anchor_key):10s} "
            f"atoms={len(coords):6d}  "
            f"anchor RMSD={maximum:.6f} Å"
        )

    except Exception as exc:
        summary_rows.append({
            "input_file": path.name,
            "status": "FAILED",
            "selected_mobile_anchor": "",
            "atom_count": "",
            "max_anchor_RMSD_A": "",
            "aligned_pdb": "",
            "json_report": "",
            "error": str(exc)
        })
        print(f"FAILED  {path.name}: {exc}")

summary_path = OUTPUT_DIR / "batch_alignment_summary.csv"

with summary_path.open("w", newline="") as fh:
    writer = csv.DictWriter(
        fh,
        fieldnames=[
            "input_file",
            "status",
            "selected_mobile_anchor",
            "atom_count",
            "max_anchor_RMSD_A",
            "aligned_pdb",
            "json_report",
            "error"
        ]
    )
    writer.writeheader()
    writer.writerows(summary_rows)

print("\nDone.")
print("Summary CSV:", summary_path)


Reference: /home/chiara/Desktop/COMENZE/Surfmatch_pipeline/Nylon_surface/Nylon_surfmap/NYL_newVer_rotY90resnum.pdb
Reference centroid (Å): [15.68611806 33.75986294 20.48624415]
Fixed reference anchor: A:1
Found 7 PDB file(s).
Mobile anchor: selected automatically for each cube.
All PDBs are aligned independently to the SAME reference coordinate frame.

OK  03_Nylon328_30A_final_clean.pdb     anchor=_:82       atoms=  3192  anchor RMSD=0.000643 Å
OK  03_Nylon428_40A_final_clean.pdb     anchor=_:114      atoms=  4256  anchor RMSD=0.000643 Å
OK  03_Nylon429_40A_final_clean.pdb     anchor=_:146      atoms=  4864  anchor RMSD=0.000671 Å
OK  03_Nylon5311_50A_final_clean.pdb    anchor=_:267      atoms= 11400  anchor RMSD=0.000551 Å
OK  03_Nylon6313_60A_final_clean.pdb    anchor=_:471      atoms= 16416  anchor RMSD=0.000438 Å
OK  03_Nylon7415_70A_final_clean.pdb    anchor=_:724      atoms= 29792  anchor RMSD=0.000414 Å
OK  03_Nylon9518_80A_final_clean.pdb    anchor=_:1525     atoms= 58140  anc

## 3D visual control of the alignment

The cells below provide a visual check for every aligned structure.

For each PDB, the plot shows:

- **aligned mobile structure**
- **reference structure**
- the aligned SURFMAP direction vector **[-1, 0, 0]**
- the geometric centroid of the aligned structure
- the anchor atoms used for the fit

The structures are displayed as 3D atom clouds. This is meant as an **orientation/alignment audit**, not as a molecular rendering with bonds.

You can rotate, zoom and pan the plot interactively.

In [5]:
# =========================
# INTERACTIVE 3D VISUAL CONTROL
# =========================
import numpy as np
import plotly.graph_objects as go
from pathlib import Path

ALIGNMENT_VECTOR = np.array([-1.0, 0.0, 0.0])

def get_atom_table(structure):
    """Return atom coordinates and simple labels from a Structure object."""
    labels = []
    atom_names = []
    residue_labels = []

    for line_index in structure.atom_lines:
        line = structure.lines[line_index]
        atom_name = line[12:16].strip()
        resname = line[17:20].strip()
        chain = line[21] if line[21].strip() else "_"
        resid = line[22:26].strip()
        icode = line[26].strip()

        atom_names.append(atom_name)
        residue_labels.append(f"{resname} {chain}:{resid}{icode}")
        labels.append(f"{atom_name} | {resname} {chain}:{resid}{icode}")

    return {
        "xyz": structure.xyz.copy(),
        "labels": labels,
        "atom_names": atom_names,
        "residue_labels": residue_labels,
    }


def transformed_structure_xyz(structure, report):
    """Apply the saved rigid-body transform from the alignment report."""
    rotation = np.asarray(report["rotation_row"], dtype=float)
    shift = np.asarray(report["translation_A"], dtype=float)
    return structure.xyz @ rotation + shift


def anchor_indices(structure, keys, atom_names):
    """Return atom indices belonging to the selected anchor residue(s)."""
    indices = []
    for key in keys:
        residue = structure.residues.get(key)
        if residue is None:
            continue
        for atom_name in atom_names:
            idx = residue["atoms"].get(atom_name)
            if idx is not None:
                indices.append(idx)
    return indices


def add_direction_arrow(fig, origin, direction, length, name="Alignment vector"):
    """
    Add an arrow composed of a line + cone.
    Direction is normalized before plotting.
    """
    direction = np.asarray(direction, dtype=float)
    norm = np.linalg.norm(direction)
    if norm == 0:
        raise ValueError("Direction vector cannot be zero.")
    unit = direction / norm

    start = np.asarray(origin, dtype=float)
    end = start + unit * length

    fig.add_trace(go.Scatter3d(
        x=[start[0], end[0]],
        y=[start[1], end[1]],
        z=[start[2], end[2]],
        mode="lines",
        line=dict(width=8),
        name=name,
        hoverinfo="skip"
    ))

    fig.add_trace(go.Cone(
        x=[end[0]],
        y=[end[1]],
        z=[end[2]],
        u=[unit[0]],
        v=[unit[1]],
        w=[unit[2]],
        sizemode="absolute",
        sizeref=max(length * 0.12, 1.0),
        anchor="tip",
        showscale=False,
        name=f"{name} arrowhead",
        hoverinfo="skip"
    ))

    return start, end


def visualize_alignment_3d(
    mobile_path,
    reference,
    reference_key,
    names,
    resname="NYL",
    center="reference",
    rmsd_limit=0.15,
    vector=None,
    vector_length=None,
    show_reference=True,
    show_anchors=True,
    marker_size=3,
):
    """
    Align one structure using the same alignment routine, then display it in 3D.

    The aligned mobile and the reference are plotted in the same coordinate frame.
    The vector defaults to the SURFMAP audited direction [-1, 0, 0].
    """
    mobile_path = Path(mobile_path)
    mobile = read_pdb(mobile_path)

    mobile_anchor_key, _ = choose_mobile_anchor(
        mobile,
        reference,
        reference_key,
        names,
        resname=resname,
        rmsd_limit=rmsd_limit,
    )

    pairs = [(mobile_anchor_key, reference_key)]

    # Re-run EXACTLY the same alignment used in the batch procedure.
    _, report = align_one(
        mobile,
        reference,
        pairs,
        names,
        resname,
        center,
        rmsd_limit
    )

    aligned_xyz = transformed_structure_xyz(mobile, report)
    mobile_info = get_atom_table(mobile)
    ref_info = get_atom_table(reference)

    centroid = aligned_xyz.mean(axis=0)

    # Choose a conservative arrow length relative to the molecular extent.
    extent = np.ptp(aligned_xyz, axis=0)
    max_extent = float(np.max(extent))
    if vector_length is None:
        vector_length = max(max_extent * 0.55, 10.0)

    if vector is None:
        vector = np.asarray(
            report.get("audited_SURFMAP_central_direction_aligned", ALIGNMENT_VECTOR),
            dtype=float
        )

    fig = go.Figure()

    # Reference
    if show_reference:
        fig.add_trace(go.Scatter3d(
            x=reference.xyz[:, 0],
            y=reference.xyz[:, 1],
            z=reference.xyz[:, 2],
            mode="markers",
            marker=dict(size=max(marker_size - 1, 1), opacity=0.28),
            text=ref_info["labels"],
            hovertemplate="REFERENCE<br>%{text}<br>x=%{x:.3f}<br>y=%{y:.3f}<br>z=%{z:.3f}<extra></extra>",
            name="Reference"
        ))

    # Aligned mobile
    fig.add_trace(go.Scatter3d(
        x=aligned_xyz[:, 0],
        y=aligned_xyz[:, 1],
        z=aligned_xyz[:, 2],
        mode="markers",
        marker=dict(size=marker_size, opacity=0.80),
        text=mobile_info["labels"],
        hovertemplate="ALIGNED<br>%{text}<br>x=%{x:.3f}<br>y=%{y:.3f}<br>z=%{z:.3f}<extra></extra>",
        name=f"Aligned: {mobile_path.name}"
    ))

    # Geometric centroid
    fig.add_trace(go.Scatter3d(
        x=[centroid[0]],
        y=[centroid[1]],
        z=[centroid[2]],
        mode="markers",
        marker=dict(size=7, symbol="diamond"),
        name="Aligned centroid",
        hovertemplate=(
            "Aligned centroid"
            "<br>x=%{x:.3f}"
            "<br>y=%{y:.3f}"
            "<br>z=%{z:.3f}"
            "<extra></extra>"
        )
    ))

    # Anchor atoms used for the mobile fit
    if show_anchors:
        mobile_anchor_keys = [mkey for mkey, _ in pairs]
        idx = anchor_indices(mobile, mobile_anchor_keys, names)
        if idx:
            idx = np.asarray(idx, dtype=int)
            fig.add_trace(go.Scatter3d(
                x=aligned_xyz[idx, 0],
                y=aligned_xyz[idx, 1],
                z=aligned_xyz[idx, 2],
                mode="markers",
                marker=dict(size=7, symbol="circle-open"),
                text=[mobile_info["labels"][i] for i in idx],
                hovertemplate="ANCHOR<br>%{text}<extra></extra>",
                name="Mobile anchor atoms"
            ))

    # Alignment / SURFMAP vector
    add_direction_arrow(
        fig,
        centroid,
        vector,
        vector_length,
        name=f"Alignment vector {np.asarray(vector).tolist()}"
    )

    maximum = max(
        row["centred_motif_RMSD_A"]
        for row in report["anchors"]
    )

    fig.update_layout(
        title=(
            f"{mobile_path.name} — 3D alignment audit"
            f"<br><sup>max anchor RMSD = {maximum:.6f} Å | "
            f"vector = {np.asarray(vector).tolist()}</sup>"
        ),
        scene=dict(
            xaxis_title="X (Å)",
            yaxis_title="Y (Å)",
            zaxis_title="Z (Å)",
            aspectmode="data",
        ),
        legend=dict(itemsizing="constant"),
        width=950,
        height=750,
        margin=dict(l=0, r=0, b=0, t=75)
    )

    fig.show()
    return report


def visualize_all_alignments(
    input_dir,
    reference,
    reference_key,
    names,
    pattern="*.pdb",
    resname="NYL",
    center="reference",
    rmsd_limit=0.15,
):
    """
    Display one interactive 3D figure for every PDB in the input directory.
    """
    input_dir = Path(input_dir)
    reference_resolved = REFERENCE_PDB.resolve()

    files = sorted(
        p for p in input_dir.glob(pattern)
        if p.is_file() and p.resolve() != reference_resolved
    )

    print(f"Displaying {len(files)} alignment(s).")

    reports = {}
    for i, path in enumerate(files, 1):
        print(f"\n[{i}/{len(files)}] {path.name}")
        reports[path.name] = visualize_alignment_3d(
            path,
            reference,
            reference_key,
            names,
            resname=resname,
            center=center,
            rmsd_limit=rmsd_limit
        )

    return reports


### Visualize one structure

Set the PDB filename below to inspect a single alignment first. This is useful before displaying the complete batch.

In [6]:
# Example: inspect ONE structure interactively
# Change the filename to one of the PDBs in INPUT_DIR.

PDB_TO_INSPECT = next(
    p for p in sorted(INPUT_DIR.glob(PATTERN))
    if p.resolve() != REFERENCE_PDB.resolve()
)

single_report = visualize_alignment_3d(
    PDB_TO_INSPECT,
    reference,
    REFERENCE_ANCHOR_KEY,
    ATOMS,
    resname=RESNAME,
    center=CENTER,
    rmsd_limit=MAX_ANCHOR_RMSD
)


### Visualize all structures

This produces **one independent interactive 3D plot for every PDB**.  
For a large number of structures, it is usually better to inspect one first and run this cell only when needed.

In [7]:
# Display ALL aligned structures one by one.
all_3d_reports = visualize_all_alignments(
    INPUT_DIR,
    reference,
    REFERENCE_ANCHOR_KEY,
    ATOMS,
    pattern=PATTERN,
    resname=RESNAME,
    center=CENTER,
    rmsd_limit=MAX_ANCHOR_RMSD
)


Displaying 7 alignment(s).

[1/7] 03_Nylon328_30A_final_clean.pdb



[2/7] 03_Nylon428_40A_final_clean.pdb



[3/7] 03_Nylon429_40A_final_clean.pdb



[4/7] 03_Nylon5311_50A_final_clean.pdb



[5/7] 03_Nylon6313_60A_final_clean.pdb



[6/7] 03_Nylon7415_70A_final_clean.pdb



[7/7] 03_Nylon9518_80A_final_clean.pdb


### What to check visually

A correct result should show:

1. the **reference** and the aligned structure with the expected common orientation;
2. the selected anchor region in the same local orientation as the reference;
3. the direction arrow pointing along **negative X**, i.e. `[-1, 0, 0]`;
4. no unexpected inversion or mirror reflection;
5. similar structures pointing in the same global direction even if their dimensions differ.

The numerical anchor RMSD remains the quantitative check. The 3D view is an additional **geometric sanity check**.